# Source-Free Adaptation for IoT IDS — Phase 3: the proposed method vs. strong baselines
**Inputs at deployment:** the trained source model + its benign feature statistics (mean and covariance of the encoder output on benign source traffic, 64 + 64×64 numbers shipped with the model, comparable to BatchNorm statistics; no source data), and a small target **benign anchor** that may be contaminated with attacks.

**Proposed method (declared before running): BARA — Benign-Anchored Robust Alignment**
1. *Robust benign statistics*: Minimum Covariance Determinant (MCD) estimate of the anchor's **pre-ReLU** feature mean/covariance (continuous, BN-normalised; tolerates contamination).
2. *Benign-to-benign alignment*: map target features so that target benign statistics match source benign statistics, then apply the frozen source head. Hypothesis: BN-Adapt failed because it aligned *mixed* distributions with different attack shares; aligning benign-to-benign removes that confound.
3. *Robust Mahalanobis novelty* in the source feature space.
4. *Self-cleaning anchor*: drop anchor points that are statistical outliers (median + 6·MAD on log-distance / logit-probability) **or that the re-aligned source head classifies as attacks**, refit the robust statistics once on the cleaned anchor, and drop again; *fusion*: mean of the two scores' ranks against the cleaned anchor; threshold = its (1−α) quantile.

*Known trade-off (stated before running):* without labels a benign tail flow and a mild attack in the anchor are indistinguishable, so cleaning removes some benign tail and raises FPR above α; the method is judged against an operational FPR budget of 5 %.

**Ablations:** each component alone; post- vs pre-ReLU features; plain vs. MCD statistics in novelty and in alignment. **Baselines:** source-only, Mahalanobis (plain), autoencoder, Isolation Forest, oracle.
Anchor 1000 flows; contamination 0 / 1 / 5 / 10 %; α = 1 %; 12 directions × 3 seeds × 2 priors.

**Pre-registered decision:** GO if `bara_fused` beats the best baseline by ≥ 0.10 median gap-recovery at 5 % contamination, is not worse by > 0.03 at 0 %, keeps median FPR ≤ 5 % (operational budget), and the paired Wilcoxon test is significant (p < 0.05). If a single component beats the fusion, that component becomes the method and this is reported.

In [ ]:
# ===== 1. Setup =====
import os, glob, json, time, math, random, copy
import numpy as np, pandas as pd
import torch, torch.nn as nn, torch.nn.functional as F
from sklearn.metrics import f1_score, roc_auc_score
from sklearn.ensemble import IsolationForest
from sklearn.covariance import MinCovDet
from scipy.stats import wilcoxon
try:
    from google.colab import drive
    drive.mount('/content/drive'); ROOT = '/content/drive/MyDrive'
except Exception:
    ROOT = '.'
OUT = f'{ROOT}/sfda_ids_phase3'; os.makedirs(OUT, exist_ok=True)
P1 = f'{ROOT}/sfda_ids_phase1'
device = 'cuda' if torch.cuda.is_available() else 'cpu'
print('device:', device, '| results ->', OUT)

CFG = dict(
    datasets={'ton': 'dhoogla/nftoniotv2', 'unsw': 'dhoogla/nfunswnb15v2', 'bot': 'dhoogla/nfbotiotv2', 'cic': 'dhoogla/nfcsecicids2018v2'},
    required=['ton', 'unsw'], attack_rate={'ton': 0.6399, 'unsw': 0.0398, 'bot': 0.9964, 'cic': 0.1195},
    n_per_dataset=300_000, test_frac=0.3, seeds=[0, 1, 2], hidden=[128, 64], src_epochs=5, bs=512, lr=1e-3,
    priors=['natural', 0.05], n_target_test=40_000, alpha=0.01, anchor=1000, contaminations=[0.0, 0.01, 0.05, 0.10],
    artifacts=['MIN_TTL', 'MAX_TTL', 'TCP_WIN_MAX_IN', 'TCP_WIN_MAX_OUT'], ae_steps=1500, mad_k=6.0, ridge=1e-3, min_kept=100, fpr_budget=0.05,
    go_margin=0.10, clean_tolerance=0.03)
json.dump(CFG, open(f'{OUT}/config.json', 'w'), indent=2)
DROP = ['IPV4_SRC_ADDR', 'IPV4_DST_ADDR', 'L4_SRC_PORT', 'L4_DST_PORT', 'DNS_QUERY_ID', 'Dataset']
NEG = ['0', '0.0', 'benign', 'false', 'normal']
def set_seed(s):
    random.seed(s); np.random.seed(s); torch.manual_seed(s); torch.cuda.manual_seed_all(s)

Mounted at /content/drive
device: cuda | results -> /content/drive/MyDrive/sfda_ids_phase3


In [ ]:
# ===== 2. Data (reuses Phase 1 samples on Drive) =====
def label_of(df):
    cols = {c.lower(): c for c in df.columns}; lab = cols.get('label')
    return (~df[lab].astype(str).str.strip().str.lower().isin(NEG)).values

def load_nf(key, slug, n, seed=0):
    for path in (f'{P1}/data_{key}_{n}.parquet', f'{OUT}/data_{key}_{n}.parquet'):
        if os.path.exists(path): print(key, 'loaded', path); return pd.read_parquet(path)
    import kagglehub, pyarrow.parquet as pq
    root = kagglehub.dataset_download(slug)
    pfs = [pq.ParquetFile(f) for f in sorted(glob.glob(os.path.join(root, '**', '*.parquet'), recursive=True))]
    tot = sum(p.metadata.num_rows for p in pfs); r = CFG['attack_rate'][key]; rs = np.random.RandomState(seed); parts = []
    for p in pfs:
        for b in p.iter_batches(batch_size=1_000_000):
            d = b.to_pandas(); y = label_of(d)
            parts.append(d[rs.rand(len(d)) < np.where(y, min(1, .65 * n / (tot * r)), min(1, .65 * n / (tot * (1 - r))))])
    df = pd.concat(parts, ignore_index=True)
    if len(df) > n: df = df.sample(n=n, random_state=seed).reset_index(drop=True)
    df.to_parquet(f'{OUT}/data_{key}_{n}.parquet'); return df

def prepare(df):
    cols = {c.lower(): c for c in df.columns}; lab, att = cols.get('label'), cols.get('attack')
    y = label_of(df).astype(np.int64)
    X = df.drop(columns=[c for c in [lab, att] + DROP if c is not None and c in df.columns])
    X = X.apply(lambda c: pd.to_numeric(c.astype(str) if str(c.dtype) in ('category', 'object', 'bool') else c, errors='coerce'))
    return X.loc[:, X.notna().any()].fillna(0.0), y

def build_data(raw):
    prep = {k: prepare(v) for k, v in raw.items()}
    common = [c for c in sorted(set.intersection(*[set(p[0].columns) for p in prep.values()])) if c not in CFG['artifacts']]
    data = {}
    for k, (X, y) in prep.items():
        V = X[common].values; Xl = (np.sign(V) * np.log1p(np.abs(V))).astype(np.float32)
        idx = np.random.RandomState(0).permutation(len(y)); nt = int(CFG['test_frac'] * len(y))
        data[k] = dict(Xtr=Xl[idx[nt:]], ytr=y[idx[nt:]], Xte=Xl[idx[:nt]], yte=y[idx[:nt]])
    print(f'{len(common)} features (artifacts removed)'); return data, common

In [ ]:
# ===== 3. Source model, baselines, and the BARA components =====
class Net(nn.Module):
    def __init__(s, d, h, k=2):
        super().__init__()
        s.f = nn.Sequential(nn.Linear(d, h[0]), nn.BatchNorm1d(h[0]), nn.ReLU(), nn.Linear(h[0], h[1]), nn.BatchNorm1d(h[1]), nn.ReLU())
        s.h = nn.Linear(h[1], k)
    def forward(s, x): return s.h(s.f(x))
def T(x): return torch.as_tensor(x, device=device)

def train_sup(X, y, seed, epochs):
    set_seed(seed); m = Net(X.shape[1], CFG['hidden']).to(device); opt = torch.optim.Adam(m.parameters(), CFG['lr'])
    Xt, yt = T(X), T(y); g = torch.Generator().manual_seed(seed)
    for _ in range(epochs):
        m.train(); perm = torch.randperm(len(Xt), generator=g).to(device)
        for i in range(0, len(perm), CFG['bs']):
            b = perm[i:i + CFG['bs']]
            if len(b) > 1: opt.zero_grad(); F.cross_entropy(m(Xt[b]), yt[b]).backward(); opt.step()
    return m.eval()

@torch.no_grad()
def feats(m, X):
    m.eval(); Xt = T(X)
    return torch.cat([m.f(Xt[i:i + 8192]) for i in range(0, len(Xt), 8192)]).cpu().numpy().astype(np.float64)

@torch.no_grad()
def feats_pre(m, X):
    m.eval(); Xt = T(X); body = m.f[:-1]                      # encoder without its final ReLU (continuous, BN-normalised)
    return torch.cat([body(Xt[i:i + 8192]) for i in range(0, len(Xt), 8192)]).cpu().numpy().astype(np.float64)

def head_np(m):
    return m.h.weight.detach().cpu().numpy().astype(np.float64), m.h.bias.detach().cpu().numpy().astype(np.float64)

def attack_prob(Z, W, b, relu=False):
    if relu: Z = np.maximum(Z, 0)
    l = Z @ W.T + b; return 1 / (1 + np.exp(-np.clip(l[:, 1] - l[:, 0], -50, 50)))

def msqrt(S, inv=False):
    w, V = np.linalg.eigh((S + S.T) / 2); w = np.clip(w, 1e-6, None)
    return (V * (w ** (-0.5 if inv else 0.5))) @ V.T

def gauss(Z, robust, seed):
    keep = Z.std(0) > 1e-8; Zk = Z[:, keep]; p = Zk.shape[1]
    mu, C = Z.mean(0), np.cov(Z, rowvar=False)
    if robust and len(Zk) > 2 * p + 2:
        try:
            mcd = MinCovDet(random_state=seed).fit(Zk)
            mu = mu.copy(); mu[keep] = mcd.location_
            C = C.copy(); C[np.ix_(keep, keep)] = mcd.covariance_
        except Exception as e:
            print('  MCD failed, plain covariance used:', str(e)[:80])
    return mu, C + CFG['ridge'] * np.eye(len(mu))

def maha(Z, mu, C):
    D = Z - mu; return np.sqrt(np.maximum(np.einsum('ij,jk,ik->i', D, np.linalg.pinv(C), D), 0))

def outliers(s, kind):
    # robust upper-tail outlier flags on a symmetrising transform: log for distances, logit for probabilities
    s = np.asarray(s, float)
    t = np.log(s + 1e-12) if kind == 'dist' else np.log(np.clip(s, 1e-12, 1 - 1e-12) / (1 - np.clip(s, 1e-12, 1 - 1e-12)))
    med = np.median(t); mad = 1.4826 * np.median(np.abs(t - med)) + 1e-12
    return t > med + CFG['mad_k'] * mad

def threshold(s_anchor, keep=None):
    s = np.asarray(s_anchor); s = s if keep is None else s[keep]
    return np.quantile(s, 1 - CFG['alpha'])

def ecdf(ref, x):
    r = np.sort(ref); return np.searchsorted(r, x, side='right') / len(r)

def ae_scores(Xa, Xe, seed):
    set_seed(seed); d = Xa.shape[1]
    ae = nn.Sequential(nn.Linear(d, 32), nn.ReLU(), nn.Linear(32, 8), nn.ReLU(), nn.Linear(8, 32), nn.ReLU(), nn.Linear(32, d)).to(device)
    opt = torch.optim.Adam(ae.parameters(), 1e-3, weight_decay=1e-5); A = T(Xa)
    for _ in range(max(1, CFG['ae_steps'] // math.ceil(len(A) / 64))):
        perm = torch.randperm(len(A), device=device)
        for i in range(0, len(A), 64):
            b = perm[i:i + 64]; opt.zero_grad(); F.mse_loss(ae(A[b]), A[b]).backward(); opt.step()
    ae.eval()
    with torch.no_grad():
        E = T(Xe); ee = torch.cat([((ae(E[i:i + 8192]) - E[i:i + 8192]) ** 2).mean(1) for i in range(0, len(E), 8192)])
        ea = ((ae(A) - A) ** 2).mean(1)
    return ea.cpu().numpy(), ee.cpu().numpy()

def metrics(y, pred, score):
    pos, neg = y == 1, y == 0
    tpr = ((pred == 1) & pos).sum() / max(pos.sum(), 1); fpr = ((pred == 1) & neg).sum() / max(neg.sum(), 1)
    auc = roc_auc_score(y, score) if 0 < y.mean() < 1 and np.isfinite(score).all() else np.nan
    return dict(macro_f1=f1_score(y, pred, average='macro', zero_division=0), attack_recall=float(tpr), fpr=float(fpr), auroc=float(auc))

def resample(X, y, prior, n, seed):
    rs = np.random.RandomState(seed); att, ben = np.where(y == 1)[0], np.where(y == 0)[0]
    n = int(min(n, len(att) / prior, len(ben) / (1 - prior))); na = int(round(prior * n))
    idx = rs.permutation(np.concatenate([rs.choice(att, na, replace=False), rs.choice(ben, n - na, replace=False)]))
    return X[idx], y[idx]

def make_anchor(X, y, size, contam, seed):
    rs = np.random.RandomState(seed); na = int(round(contam * size))
    ben, att = np.where(y == 0)[0], np.where(y == 1)[0]
    idx = np.concatenate([rs.choice(ben, size - na, replace=False), rs.choice(att, na, replace=False) if na else np.array([], int)])
    return X[idx]

In [ ]:
# ===== 4. One evaluation block: all methods for one anchor =====
def eval_block(src, mu_s, C_s, Xa, Xe, ye, seed):
    W, b = head_np(src); rows = []
    def add(name, s_a, s_e, keep=None):
        th = threshold(s_a, keep); rows.append(dict(method=name, **metrics(ye, (s_e > th).astype(int), s_e)))
    # --- baselines (Phase 2 definitions) ---
    Za, Ze = feats(src, Xa), feats(src, Xe)
    mu0, C0 = gauss(Za, False, seed); add('maha_plain', maha(Za, mu0, C0), maha(Ze, mu0, C0))
    ea, ee = ae_scores(Xa, Xe, seed); add('autoencoder', ea, ee)
    iso = IsolationForest(n_estimators=200, random_state=seed).fit(Xa); add('iforest', -iso.score_samples(Xa), -iso.score_samples(Xe))
    # --- BARA components on pre-ReLU features ---
    Pa, Pe = feats_pre(src, Xa), feats_pre(src, Xe)
    mu_p, C_p = gauss(Pa, False, seed); mu_r, C_r = gauss(Pa, True, seed)
    add('maha_pre_plain', maha(Pa, mu_p, C_p), maha(Pe, mu_p, C_p))
    da, de = maha(Pa, mu_r, C_r), maha(Pe, mu_r, C_r); add('maha_pre_mcd', da, de)
    A_p = msqrt(C_p, inv=True) @ msqrt(C_s); pe_p = attack_prob((Pe - mu_p) @ A_p + mu_s, W, b, relu=True)
    rows.append(dict(method='align_plain_head', **metrics(ye, (pe_p > 0.5).astype(int), pe_p)))
    A_r = msqrt(C_r, inv=True) @ msqrt(C_s)
    pa, pe = attack_prob((Pa - mu_r) @ A_r + mu_s, W, b, relu=True), attack_prob((Pe - mu_r) @ A_r + mu_s, W, b, relu=True)
    rows.append(dict(method='bara_align_head', **metrics(ye, (pe > 0.5).astype(int), pe)))
    # self-cleaning anchor: statistical outliers + points the re-aligned source head calls attacks, then refit once
    keep = ~(outliers(da, 'dist') | outliers(pa, 'prob') | (pa > 0.5))
    if keep.sum() >= CFG['min_kept']:
        mu_r, C_r = gauss(Pa[keep], True, seed); A_r = msqrt(C_r, inv=True) @ msqrt(C_s)
        da, de = maha(Pa, mu_r, C_r), maha(Pe, mu_r, C_r)
        pa, pe = attack_prob((Pa - mu_r) @ A_r + mu_s, W, b, relu=True), attack_prob((Pe - mu_r) @ A_r + mu_s, W, b, relu=True)
        keep = keep & ~(pa > 0.5)
    if keep.sum() < CFG['min_kept']: keep = np.ones(len(Pa), bool)
    add('bara_novelty', da, de, keep); add('bara_align', pa, pe, keep)
    fa = (ecdf(da[keep], da) + ecdf(pa[keep], pa)) / 2; fe = (ecdf(da[keep], de) + ecdf(pa[keep], pe)) / 2
    add('bara_fused', fa, fe, keep)
    rows.append(dict(method='_anchor_kept_frac', macro_f1=float(keep.mean()), attack_recall=np.nan, fpr=np.nan, auroc=np.nan))
    return rows

def run_all(data, pairs, out_prefix, seeds):
    csv = f'{out_prefix}_metrics.csv'; done = set()
    if os.path.exists(csv):
        d = pd.read_csv(csv); done = set(zip(d.seed, d.src, d.tgt, d.prior.astype(str)))
    for seed in seeds:
        for s, t in pairs:
            todo = [p for p in CFG['priors'] if (seed, s, t, str(p)) not in done]
            if not todo: continue
            S, Tg = data[s], data[t]
            mu, sd = S['Xtr'].mean(0), S['Xtr'].std(0) + 1e-6
            norm = lambda X: np.clip((X - mu) / sd, -10, 10).astype(np.float32)
            t0 = time.time(); src = train_sup(norm(S['Xtr']), S['ytr'], seed, CFG['src_epochs'])
            Zs = feats_pre(src, norm(S['Xtr'][S['ytr'] == 0][:50_000]))        # benign pre-ReLU statistics shipped with the model
            mu_s, C_s = Zs.mean(0), np.cov(Zs, rowvar=False) + CFG['ridge'] * np.eye(Zs.shape[1])
            W, b = head_np(src)
            for prior in todo:
                pe = CFG['attack_rate'][t] if prior == 'natural' else prior
                Xe, ye = resample(Tg['Xte'], Tg['yte'], pe, CFG['n_target_test'], seed + 100); Xe = norm(Xe)
                p_src = attack_prob(feats(src, Xe), W, b)
                rows = [dict(method='source_only', contam=0.0, **metrics(ye, (p_src > 0.5).astype(int), p_src))]
                Xo, yo = resample(Tg['Xtr'], Tg['ytr'], pe, 100_000, seed)
                orc = train_sup(norm(Xo), yo, seed, CFG['src_epochs']); W_o, b_o = head_np(orc); p_o = attack_prob(feats(orc, Xe), W_o, b_o)
                rows.append(dict(method='oracle', contam=0.0, **metrics(ye, (p_o > 0.5).astype(int), p_o)))
                for c in CFG['contaminations']:
                    Xa = norm(make_anchor(Tg['Xtr'], Tg['ytr'], CFG['anchor'], c, seed))
                    for r in eval_block(src, mu_s, C_s, Xa, Xe, ye, seed): r['contam'] = c; rows.append(r)
                for r in rows: r.update(seed=seed, src=s, tgt=t, prior=str(prior), true_attack_rate=float(ye.mean()))
                pd.DataFrame(rows).to_csv(csv, mode='a', header=not os.path.exists(csv), index=False)
                brief = {r['method']: round(r['macro_f1'], 3) for r in rows if r['contam'] == 0.05 or r['method'] in ('source_only', 'oracle')}
                print(f'seed {seed} {s}->{t} prior {prior} [contam 5%]: {brief} ({(time.time()-t0)/60:.1f} min)', flush=True)
    return pd.read_csv(csv)

## Self-test on synthetic data — must print SELF-TEST PASSED

In [ ]:
# ===== 5. Self-test =====
def synth(n, shift, prior, seed):
    rs = np.random.RandomState(seed); y = (rs.rand(n) < prior).astype(np.int64)
    return (rs.randn(n, 8).astype(np.float32) + y[:, None] * 1.5 + shift).astype(np.float32), y
fake = {}
for i, (k, sh, pr) in enumerate([('A', 0.0, 0.6), ('B', 0.8, 0.3)]):
    X, y = synth(9000, sh, pr, i); fake[k] = dict(Xtr=X[2000:], ytr=y[2000:], Xte=X[:2000], yte=y[:2000])
_save = copy.deepcopy(CFG); CFG.update(n_target_test=1000, attack_rate={'A': 0.6, 'B': 0.3}, ae_steps=20, src_epochs=2, anchor=300)
for f in glob.glob(f'{OUT}/selftest_*'): os.remove(f)
mt = run_all(fake, [('A', 'B')], f'{OUT}/selftest', [0])
CFG.clear(); CFG.update(_save)
n_methods = 11   # 10 methods + anchor-kept diagnostic
assert len(mt) == 2 * (2 + 4 * n_methods), f'self-test incomplete: {len(mt)} rows'
assert mt.macro_f1.notna().all(), 'NaN metric in self-test'
assert set(mt.method) >= {'bara_fused', 'bara_align', 'bara_novelty', 'bara_align_head', 'align_plain_head', 'maha_pre_mcd', 'maha_pre_plain', 'maha_plain', 'autoencoder', 'iforest'}
print('SELF-TEST PASSED')
print(mt[mt.contam.isin([0.0, 0.05])].pivot_table(index='method', columns=['prior', 'contam'], values='macro_f1').round(3).to_string())

seed 0 A->B prior natural [contam 5%]: {'source_only': 0.636, 'oracle': 0.945, 'maha_plain': 0.701, 'autoencoder': 0.596, 'iforest': 0.593, 'maha_pre_plain': 0.753, 'maha_pre_mcd': 0.67, 'align_plain_head': 0.687, 'bara_align_head': 0.906, 'bara_novelty': 0.874, 'bara_align': 0.943, 'bara_fused': 0.938, '_anchor_kept_frac': 0.963} (0.2 min)
seed 0 A->B prior 0.05 [contam 5%]: {'source_only': 0.426, 'oracle': 0.725, 'maha_plain': 0.635, 'autoencoder': 0.697, 'iforest': 0.697, 'maha_pre_plain': 0.682, 'maha_pre_mcd': 0.767, 'align_plain_head': 0.794, 'bara_align_head': 0.925, 'bara_novelty': 0.905, 'bara_align': 0.953, 'bara_fused': 0.955, '_anchor_kept_frac': 0.963} (0.2 min)
SELF-TEST PASSED
prior               0.05        natural       
contam              0.00   0.05    0.00   0.05
method                                        
_anchor_kept_frac  1.000  0.963   1.000  0.963
align_plain_head   0.888  0.794   0.803  0.687
autoencoder        0.871  0.697   0.837  0.596
bara_align       

## Real data

In [ ]:
# ===== 6. Load and run =====
raw = {}
for k, slug in CFG['datasets'].items():
    try: raw[k] = load_nf(k, slug, CFG['n_per_dataset'])
    except Exception as e:
        if k in CFG['required']: raise
        print('SKIPPED', k, e)
DATA, FEATS = build_data(raw); del raw
keys = list(DATA); PAIRS = [(s, t) for s in keys for t in keys if s != t]
MT = run_all(DATA, PAIRS, f'{OUT}/real', CFG['seeds'])
print('done:', len(MT), 'rows')

ton loaded /content/drive/MyDrive/sfda_ids_phase1/data_ton_300000.parquet
unsw loaded /content/drive/MyDrive/sfda_ids_phase1/data_unsw_300000.parquet
bot loaded /content/drive/MyDrive/sfda_ids_phase1/data_bot_300000.parquet
cic loaded /content/drive/MyDrive/sfda_ids_phase1/data_cic_300000.parquet
34 features (artifacts removed)


/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-622.104613277567978 > -622.138986426667088). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-606.345269434805118 > -606.353104431163615). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-624.607682445067098 > -625.006392400901632). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local

seed 0 ton->unsw prior natural [contam 5%]: {'source_only': 0.361, 'oracle': 0.965, 'maha_plain': 0.665, 'autoencoder': 0.625, 'iforest': 0.671, 'maha_pre_plain': 0.658, 'maha_pre_mcd': 0.573, 'align_plain_head': 0.528, 'bara_align_head': 0.461, 'bara_novelty': 0.519, 'bara_align': 0.477, 'bara_fused': 0.498, '_anchor_kept_frac': 0.723} (0.8 min)


/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-622.104613277567978 > -622.138986426667088). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-606.345269434805118 > -606.353104431163615). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-624.607682445067098 > -625.006392400901632). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local

seed 0 ton->unsw prior 0.05 [contam 5%]: {'source_only': 0.37, 'oracle': 0.971, 'maha_plain': 0.672, 'autoencoder': 0.627, 'iforest': 0.675, 'maha_pre_plain': 0.66, 'maha_pre_mcd': 0.571, 'align_plain_head': 0.536, 'bara_align_head': 0.46, 'bara_novelty': 0.518, 'bara_align': 0.483, 'bara_fused': 0.506, '_anchor_kept_frac': 0.723} (1.6 min)


...

seed 2 cic->unsw prior 0.05 [contam 5%]: {'source_only': 0.5, 'oracle': 0.972, 'maha_plain': 0.664, 'autoencoder': 0.638, 'iforest': 0.566, 'maha_pre_plain': 0.686, 'maha_pre_mcd': 0.581, 'align_plain_head': 0.505, 'bara_align_head': 0.529, 'bara_novelty': 0.579, 'bara_align': 0.488, 'bara_fused': 0.513, '_anchor_kept_frac': 0.846} (1.9 min)


/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-1902.988157521656149 > -1908.065781297352032). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-1930.980520942857311 > -1931.722504582227657). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-1905.279228015304852 > -1906.236448614258734). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr

seed 2 cic->bot prior natural [contam 5%]: {'source_only': 0.059, 'oracle': 0.916, 'maha_plain': 0.033, 'autoencoder': 0.054, 'iforest': 0.004, 'maha_pre_plain': 0.047, 'maha_pre_mcd': 0.004, 'align_plain_head': 0.005, 'bara_align_head': 0.059, 'bara_novelty': 0.004, 'bara_align': 0.302, 'bara_fused': 0.302, '_anchor_kept_frac': 0.798} (0.8 min)


/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-1902.988157521656149 > -1908.065781297352032). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-1930.980520942857311 > -1931.722504582227657). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/sklearn/covariance/_robust_covariance.py:185: RuntimeWarning: Determinant has increased; this should not happen: log(det) > log(previous_det) (-1905.279228015304852 > -1906.236448614258734). You may want to try with a higher value of support_fraction (current value: 0.535).
  warnings.warn(
/usr

seed 2 cic->bot prior 0.05 [contam 5%]: {'source_only': 0.297, 'oracle': 0.998, 'maha_plain': 0.504, 'autoencoder': 0.531, 'iforest': 0.485, 'maha_pre_plain': 0.517, 'maha_pre_mcd': 0.484, 'align_plain_head': 0.485, 'bara_align_head': 0.455, 'bara_novelty': 0.485, 'bara_align': 0.498, 'bara_fused': 0.499, '_anchor_kept_frac': 0.798} (1.6 min)
done: 3312 rows


In [ ]:
# ===== 7. Analysis and pre-registered decision =====
MT = pd.read_csv(f'{OUT}/real_metrics.csv'); MT['prior'] = MT.prior.astype(str)
cell = ['src', 'tgt', 'prior']
ref = MT[MT.method.isin(['source_only', 'oracle'])].groupby(cell + ['method']).macro_f1.mean().unstack('method')
gap = ref['oracle'] - ref['source_only']
KEPT = MT[MT.method == '_anchor_kept_frac'].groupby('contam').macro_f1.describe()[['mean', 'min']].round(3)
print('Fraction of anchor kept after self-cleaning (by true contamination):'); print(KEPT.to_string())
M = MT[~MT.method.isin(['source_only', 'oracle', '_anchor_kept_frac'])].groupby(cell + ['contam', 'method'])[['macro_f1', 'fpr', 'attack_recall', 'auroc']].mean().reset_index()
M = M.merge(ref.reset_index()[cell + ['source_only']], on=cell).merge(gap.rename('gap').reset_index(), on=cell)
M['recovery'] = (M.macro_f1 - M.source_only) / M.gap.where(M.gap > 0.05)
M.to_csv(f'{OUT}/per_cell.csv', index=False)

S = M.groupby(['contam', 'method']).agg(median_recovery=('recovery', 'median'), median_f1=('macro_f1', 'median'),
                                         median_fpr=('fpr', 'median'), median_recall=('attack_recall', 'median'),
                                         median_auroc=('auroc', 'median'), cells_rec_ge_0_7=('recovery', lambda v: int((v >= 0.7).sum()))).round(3)
S.to_csv(f'{OUT}/summary.csv'); print('Summary by contamination (24 cells = 12 directions x 2 priors):'); print(S.to_string())

BASE = ['maha_plain', 'autoencoder', 'iforest']
R = M.pivot_table(index=cell + ['contam'], columns='method', values='recovery')
def compare(c, method):
    sub = R.xs(c, level='contam')
    best_base = sub[BASE].median().idxmax()
    d = (sub[method] - sub[best_base]).dropna()
    p = wilcoxon(sub[method].loc[d.index], sub[best_base].loc[d.index]).pvalue if len(d) > 5 and (d != 0).any() else np.nan
    return dict(contam=c, method=method, best_baseline=best_base, median_method=round(float(sub[method].median()), 3),
                median_baseline=round(float(sub[best_base].median()), 3), median_diff=round(float(d.median()), 3),
                wins=int((d > 0).sum()), cells=int(len(d)), wilcoxon_p=float(p))
CMP = pd.DataFrame([compare(c, m) for c in CFG['contaminations'] for m in ['bara_fused', 'bara_novelty', 'bara_align', 'bara_align_head']])
CMP.to_csv(f'{OUT}/comparison.csv', index=False); print('\nProposed / components vs. best baseline (per contamination):'); print(CMP.to_string(index=False))

print('\nAblation (median recovery): post- vs pre-ReLU, plain vs MCD, plain vs robust alignment, self-cleaning threshold, fusion:')
print(S['median_recovery'].unstack('method')[['maha_plain', 'maha_pre_plain', 'maha_pre_mcd', 'bara_novelty', 'align_plain_head', 'bara_align_head', 'bara_align', 'bara_fused']].to_string())

def row(c): return CMP[(CMP.contam == c) & (CMP.method == 'bara_fused')].iloc[0]
r5, r0 = row(0.05), row(0.0)
fpr5 = float(S.loc[(0.05, 'bara_fused'), 'median_fpr'])
crit = dict(beats_by_margin_at_5pct=bool(r5.median_method - r5.median_baseline >= CFG['go_margin']),
            not_worse_clean=bool(r0.median_method - r0.median_baseline >= -CFG['clean_tolerance']),
            fpr_ok=bool(fpr5 <= CFG['fpr_budget']), significant=bool(r5.wilcoxon_p < 0.05))
best_comp = CMP[CMP.contam == 0.05].sort_values('median_method', ascending=False).iloc[0]
dec = dict(criteria=crit, best_at_5pct=best_comp.method,
           decision='GO: BARA (fused) meets all pre-registered criteria' if all(crit.values())
                    else f'NOT MET: {[k for k, v in crit.items() if not v]} — best at 5% contamination is {best_comp.method}; inspect per_cell.csv before any claim')
json.dump(dec, open(f'{OUT}/decision.json', 'w'), indent=2); print('\n', json.dumps(dec, indent=2))

Fraction of anchor kept after self-cleaning (by true contamination):
         mean    min
contam              
0.00    0.802  0.524
0.01    0.801  0.515
0.05    0.810  0.443
0.10    0.820  0.451
Summary by contamination (24 cells = 12 directions x 2 priors):
                         median_recovery  median_f1  median_fpr  median_recall  median_auroc  cells_rec_ge_0_7
contam method                                                                                                 
0.00   align_plain_head            0.110      0.488       0.006          0.029         0.316                 0
       autoencoder                 0.472      0.693       0.017          0.359         0.944                 3
       bara_align                  0.088      0.454       0.180          0.207         0.312                 0
       bara_align_head             0.083      0.475       0.181          0.174         0.333                 0
       bara_fused                  0.100      0.479       0.163          0.

In [1]:
#!/usr/bin/env python3
"""
SFDA-IDS: OSF Pre-Registration Document Generator
===================================================
Generates the registration document to upload to osf.io.

This documents:
  1. The pre-specified success criteria for the NEW experiments (RF/XGB/100-label)
  2. Retrospective documentation of the original MLP experiments

After running this script:
  1. Open osf.io → create a free account
  2. Create project: "SFDA-IDS Evaluation — Supplementary"
  3. Upload the generated file: ./osf_registration_document.pdf
  4. Note the OSF DOI / link
  5. Add to paper Section 3.4: "Pre-specified criteria and retrospective
     registration are available at [OSF link]."

Requires: reportlab  (pip install reportlab)
"""

from pathlib import Path
from datetime import date

try:
    from reportlab.lib.pagesizes import A4
    from reportlab.lib.styles import getSampleStyleSheet, ParagraphStyle
    from reportlab.lib.units import cm
    from reportlab.lib import colors
    from reportlab.platypus import (
        SimpleDocTemplate, Paragraph, Spacer, Table, TableStyle, HRFlowable)
    HAS_REPORTLAB = True
except ImportError:
    HAS_REPORTLAB = False

TODAY = date.today().strftime('%d %B %Y')


# ─────────────────────────────────────────────────────────────
# PRE-SPECIFIED CRITERIA FOR THE EXTENDED STUDY
# ─────────────────────────────────────────────────────────────

ORIGINAL_CRITERIA = [
    ("Phase 1 — SFDA methods (MLP)",
     "Fail if no SFDA method recovers ≥ 0.50 of the gap in any of the 24 cells.\n"
     "Status: CONFIRMED FAILURE (best cell = 0.41)."),

    ("Phase 2 — Benign anchor basics (MLP)",
     "Fail if clean 1,000-flow anchor does not recover ≥ 0.70 in most cells.\n"
     "Status: CONFIRMED FAILURE (best median 0.54; ≥ 0.70 in 9 of 24 cells only)."),

    ("Phase 3 — BARA method (MLP)",
     "Criteria: (a) ≥ +0.10 over best baseline at 5% contamination, "
     "(b) ≤ −0.03 vs best baseline on clean anchor, "
     "(c) median FPR ≤ 5% at 5% contamination, "
     "(d) Wilcoxon p < 0.05 in favour of BARA.\n"
     "Status: ALL FOUR CRITERIA FAILED. Documented negative result."),
]

NEW_CRITERIA = [
    ("Criterion R1 — Architecture independence",
     "Success: At least one tree-based model (RF or XGBoost) exhibits the same "
     "rank-inversion pattern as MLP: median decision-head AUROC < 0.5 in ≥ 12 "
     "of 24 cells when evaluated source-only cross-network.\n"
     "Failure: Both RF and XGBoost reach median AUROC ≥ 0.5, suggesting the "
     "failure is MLP-specific."),

    ("Criterion R2 — EM correction on trees",
     "Success: EM prior correction recovers < 0.50 of the gap on both RF and XGBoost "
     "(consistent with MLP result of 0.01).\n"
     "Failure: EM correction recovers ≥ 0.50 on either model."),

    ("Criterion R3 — 100-label baseline value",
     "Success: 100-label logistic regression recovers ≥ 0.60 of the gap (median "
     "over 24 cells) on at least one model, demonstrating that minimal supervision "
     "solves what SFDA cannot.\n"
     "Failure: 100-label baseline recovers < 0.60 on all models."),

    ("Criterion R4 — Practical FPR of 100-label",
     "Success: Median FPR of 100-label LR ≤ 0.10 (compared to ≥ 0.30 for "
     "source-only MLP).\n"
     "Failure: FPR > 0.10."),
]

TEXT_INTRO = (
    "This document records the pre-specified success and failure criteria for the "
    "extended evaluation in the revised version of: "
    '"Why Source-Free Adaptation Fails for Cross-Network Intrusion Detection." '
    "The document was uploaded to OSF before the new experiments (Criteria R1–R4) "
    "were executed. Section A records the original criteria and outcomes from the "
    "submitted manuscript. Section B states the new criteria whose outcomes are "
    "unknown at the time of upload."
)

TEXT_CAVEATS = (
    "CAVEAT: The original Phases 1–3 experiments were not registered with an "
    "external registry before execution. Their criteria were recorded in the "
    "analysis notebooks with execution timestamps; this document provides "
    "retrospective external documentation. The new criteria (R1–R4) are "
    "genuinely prospective as of this upload date."
)


# ─────────────────────────────────────────────────────────────
# PDF GENERATION
# ─────────────────────────────────────────────────────────────

def make_pdf(out_path: Path):
    doc = SimpleDocTemplate(
        str(out_path), pagesize=A4,
        leftMargin=2.5*cm, rightMargin=2.5*cm,
        topMargin=2.5*cm, bottomMargin=2.5*cm)

    styles = getSampleStyleSheet()
    title_style = ParagraphStyle(
        'Title2', parent=styles['Title'],
        fontSize=14, spaceAfter=6)
    h1_style = ParagraphStyle(
        'H1', parent=styles['Heading1'],
        fontSize=12, spaceAfter=4, textColor=colors.HexColor('#1a3a5c'))
    h2_style = ParagraphStyle(
        'H2', parent=styles['Heading2'],
        fontSize=11, spaceAfter=3, textColor=colors.HexColor('#2683C6'))
    body_style = ParagraphStyle(
        'Body2', parent=styles['Normal'],
        fontSize=10, leading=14, spaceAfter=6)
    caveat_style = ParagraphStyle(
        'Caveat', parent=styles['Normal'],
        fontSize=9, leading=12, textColor=colors.HexColor('#555555'),
        backColor=colors.HexColor('#F5F5F5'),
        borderPadding=(6, 6, 6, 6))

    story = []

    # Title
    story.append(Paragraph(
        "Pre-Registration Document: SFDA-IDS Extended Evaluation",
        title_style))
    story.append(Paragraph(
        f"Author: Jenan Jader Msad &nbsp;&nbsp;|&nbsp;&nbsp; "
        f"Institution: ATU Karbala, Iraq &nbsp;&nbsp;|&nbsp;&nbsp; "
        f"Date: {TODAY}", body_style))
    story.append(HRFlowable(width='100%', thickness=1,
                             color=colors.HexColor('#cccccc')))
    story.append(Spacer(1, 0.3*cm))

    # Intro
    story.append(Paragraph(TEXT_INTRO, body_style))
    story.append(Spacer(1, 0.2*cm))
    story.append(Paragraph(TEXT_CAVEATS, caveat_style))
    story.append(Spacer(1, 0.4*cm))

    # Section A
    story.append(Paragraph("A. Original Criteria and Outcomes (Retrospective)",
                            h1_style))
    story.append(Paragraph(
        "These criteria were specified in the analysis notebooks before each "
        "phase was run. Outcomes are as reported in the paper.", body_style))

    for label, text in ORIGINAL_CRITERIA:
        story.append(Paragraph(label, h2_style))
        for line in text.split('\n'):
            story.append(Paragraph(line.strip(), body_style))
        story.append(Spacer(1, 0.2*cm))

    story.append(HRFlowable(width='100%', thickness=0.5,
                             color=colors.HexColor('#cccccc')))
    story.append(Spacer(1, 0.3*cm))

    # Section B
    story.append(Paragraph(
        "B. New Pre-Specified Criteria for Extended Study (Prospective)",
        h1_style))
    story.append(Paragraph(
        "These criteria are specified BEFORE executing the RF/XGBoost/100-label "
        "experiments. Outcomes are unknown at the time of this upload.", body_style))

    for label, text in NEW_CRITERIA:
        story.append(Paragraph(label, h2_style))
        for line in text.split('\n'):
            story.append(Paragraph(line.strip(), body_style))
        story.append(Spacer(1, 0.2*cm))

    # Signature
    story.append(HRFlowable(width='100%', thickness=1,
                             color=colors.HexColor('#cccccc')))
    story.append(Spacer(1, 0.3*cm))
    story.append(Paragraph(
        f"Uploaded to OSF on {TODAY} before execution of Criteria R1–R4.",
        body_style))
    story.append(Paragraph(
        "OSF project URL: [add after upload]", body_style))

    doc.build(story)
    print(f"PDF saved: {out_path}")


def make_text_fallback(out_path: Path):
    """Plain-text fallback if reportlab is not installed."""
    lines = [
        "=" * 70,
        "PRE-REGISTRATION DOCUMENT: SFDA-IDS EXTENDED EVALUATION",
        f"Author: Jenan Jader Msad | ATU Karbala | Date: {TODAY}",
        "=" * 70,
        "",
        TEXT_INTRO,
        "",
        "CAVEAT:",
        TEXT_CAVEATS,
        "",
        "=" * 70,
        "A. ORIGINAL CRITERIA AND OUTCOMES (RETROSPECTIVE)",
        "=" * 70,
    ]
    for label, text in ORIGINAL_CRITERIA:
        lines += ["", f"  [{label}]", f"  {text}"]
    lines += ["", "=" * 70,
              "B. NEW PRE-SPECIFIED CRITERIA (PROSPECTIVE — BEFORE EXECUTION)",
              "=" * 70]
    for label, text in NEW_CRITERIA:
        lines += ["", f"  [{label}]", f"  {text}"]
    lines += [
        "", "-" * 70,
        f"Uploaded to OSF on {TODAY} before execution of Criteria R1-R4.",
        "OSF project URL: [add after upload]",
    ]

    with open(out_path, 'w', encoding='utf-8') as f:
        f.write('\n'.join(lines))
    print(f"Text file saved: {out_path}")


if __name__ == '__main__':
    out_dir = Path('./results')
    out_dir.mkdir(exist_ok=True)

    if HAS_REPORTLAB:
        out = out_dir / 'osf_registration_document.pdf'
        make_pdf(out)
    else:
        print("reportlab not found — generating plain text instead.")
        print("Install with: pip install reportlab --break-system-packages")
        out = out_dir / 'osf_registration_document.txt'
        make_text_fallback(out)

    print()
    print("NEXT STEPS:")
    print("  1. Go to https://osf.io — create account")
    print("  2. New Project → 'SFDA-IDS Supplementary Registration'")
    print(f"  3. Upload: {out}")
    print("  4. Copy the project URL / DOI")
    print("  5. Add to paper Section 3.4:")
    print('     "Pre-specified criteria are retrospectively registered at')
    print('      OSF [YOUR-LINK] alongside analysis notebooks with')
    print('      execution timestamps."')


reportlab not found — generating plain text instead.
Install with: pip install reportlab --break-system-packages
Text file saved: results/osf_registration_document.txt

NEXT STEPS:
  1. Go to https://osf.io — create account
  2. New Project → 'SFDA-IDS Supplementary Registration'
  3. Upload: results/osf_registration_document.txt
  4. Copy the project URL / DOI
  5. Add to paper Section 3.4:
     "Pre-specified criteria are retrospectively registered at
      OSF [YOUR-LINK] alongside analysis notebooks with
      execution timestamps."
